In [1]:
import re
import os
import string
import unicodedata
import pandas as pd
import spacy as scy
from joblib import load
from itertools import product
from unidecode import unidecode
from sklearn.preprocessing import LabelEncoder
from sklearn.feature_extraction.text import CountVectorizer

In [2]:
import nltk
from nltk.corpus import stopwords
nltk.download('stopwords')

[nltk_data] Downloading package stopwords to
[nltk_data]     C:\Users\joaol\AppData\Roaming\nltk_data...
[nltk_data]   Package stopwords is already up-to-date!


True

In [3]:
import os
from dotenv import load_dotenv
from pathlib import Path

# Como o notebook está em 'corretor/src/3_avaliacao' e o .env em 'corretor',
# precisamos voltar duas pastas (../..) para achar o arquivo.
env_path = Path('../../.env')

# Carrega o arquivo explicitamente
load_dotenv(dotenv_path=env_path)

True

In [4]:
# texto qualquer
# tenho que tratar o dado pra ser entrada para o modelo
text = "A VITIMA RELATA QUE NO 15 DE FEVEREIRO DE 2020, POR VOLTA DAS 10H, UMA MOCA CONHECIDA COMO LUIZA BARROS ENTROU EM CONTATO COM O RELATOR POR MEIO DO APLICATIVO MENSSENGER, VINCULADO A REDE SOCIAL FACEBOOK E LOGO EM SEGUIDA PELA APLICATIVO WHATSAPP POR MEIO DO NUMERAL +55 (11) 98927-2488. O RELATOR E LUIZA COMECARAM A TER UMA CONVERSAR INTIMA POR MEIO DO APLICATIVO MENSSENGER, TODAVIA, LUIZA COMECOU A ENVIAR VIDEOS INTIMOS DA MESMA, POR OUTRO LADO, O RELATOR FEZ UM VIDEO INTIMO E ENVIOU PARA A LUIZA. ATO CONTINUO, LUIZA, ASSIM QUE RECEBEU O VIDEO DO RELATOR COMECOU A PEDIR QUANTIAS EM DINHEIRO PARA NAO DIVULGAR O VIDEO PARA SUA ESPOSA E FAMILIARES. DESTARTE, LUIZA A PRINCIPIO PEDIU O VALOR E R$8.500,00 (OITO MIL E QUINHENTO REAIS), POREM O RELATOR DISSE QUE NAO TERIA TODO ESSE DINHEIRO. TODAVIA, LUIZA ENTAO SOLICITOU A QUANTIA DE R$550,00 (QUINHENTOS E CINQUENTA REAIS) DISPONIBILIZANDO UMA CONTA DO BANCO ITAU CONTA: 19683-9 AGENCIA N 1662 BENEFICIARIA LUCIA JOSE DA SILVA, DEPOSITANDO O RELATOR O VALOR SOLICITADO, POSTERIORMENTE, A CRIMINOSA SOLICITOU OUTRO VALOR DE 500,00 (QUINHENTO REAIS) DISPONIBILIZANDO OUTRA CONTA DO BANCO MONEYGRAM NAO DISPONIBILIZADO A CONTA. REGISTRA-SE PARA DEVIDOS FINS."

In [5]:
PATH_BASE_TESTES_FINAIS = os.getenv('PATH_BASE_TESTES_FINAIS')
PATH_BASE_ANONIMIZADA_CORRETOR = os.getenv('PATH_BASE_ANONIMIZADA_CORRETOR')

In [6]:
base_relato = pd.read_csv(PATH_BASE_TESTES_FINAIS, usecols=['relato'])

In [7]:
base_relato

,relato
0,"SUBJETIVO NEFROLOGIA 220 A - ALICE MORAES , 37..."
1,SUBJETIVO FISIOTERAPIA 402 A - RAFAELA MARTINS...
2,SUBJETIVO CARDIOLOGIA 205 A - RICARDO GONÇALVE...
3,SUBJETIVO GASTROENTEROLOGIA PACIENTE : PEDRO S...
4,"SUBJETIVO ORTOPEDIA 78 A - JOANA MARTINS , 52 ..."
...,...
1881,SUBJETIVO UER - SALA LARANJA ID : CLÁUDIA SOAR...
1882,SUBJETIVO UER - SALA AMARELA ID : RENATO AUGUS...
1883,SUBJETIVO UER - SALA AMARELA ID : GERTRUDES SI...
1884,SUBJETIVO CENTRO DE SAÚDE - CONSULTÓRIO ID : E...


In [8]:
def create_df(arquivo_ou_texto):
    if isinstance(arquivo_ou_texto, str) and os.path.isfile(arquivo_ou_texto):
        df_origin = pd.read_csv(arquivo_ou_texto)
    else:
        df_origin = pd.DataFrame({'relato' : [arquivo_ou_texto]})
    
    return df_origin

In [9]:
# Se for texto
df_origin = create_df(text)
df_origin

,relato
0,A VITIMA RELATA QUE NO 15 DE FEVEREIRO DE 2020...


In [10]:
# Se for arquivo tabular ( no caso só tá funcionando pra csv)
df_origin = create_df(PATH_BASE_TESTES_FINAIS)
df_origin

,n_bop,relato,nomes
0,1,"SUBJETIVO NEFROLOGIA 220 A - ALICE MORAES , 37...","ALICE, MORAES, PAULO, SOUSA, MATOS"
1,2,SUBJETIVO FISIOTERAPIA 402 A - RAFAELA MARTINS...,"RAFAELA, MARTINS, MARIA, SILVA, FERNANDO, CRUZ..."
2,3,SUBJETIVO CARDIOLOGIA 205 A - RICARDO GONÇALVE...,"RICARDO, GONÇALVES, ANDRÉ, FERNANDA, LIMA, OLI..."
3,4,SUBJETIVO GASTROENTEROLOGIA PACIENTE : PEDRO S...,"PEDRO, SANTOS, LUISA, FERNANDES"
4,5,"SUBJETIVO ORTOPEDIA 78 A - JOANA MARTINS , 52 ...","JOANA, MARTINS, RENATA, COSTA"
...,...,...,...
1881,1882,SUBJETIVO UER - SALA LARANJA ID : CLÁUDIA SOAR...,"CLÁUDIA, SOARES, ALMEIDA, PEDRO, LARISSA, GOME..."
1882,1883,SUBJETIVO UER - SALA AMARELA ID : RENATO AUGUS...,"RENATO, AUGUSTO, MOREIRA, FERNANDA, LOPES, SAM..."
1883,1884,SUBJETIVO UER - SALA AMARELA ID : GERTRUDES SI...,"GERTRUDES, SILVA, CARNEIRO, CLARISSA, DIEGO, H..."
1884,1885,SUBJETIVO CENTRO DE SAÚDE - CONSULTÓRIO ID : E...,"ELIANA, COSTA, SILVA, MARIANA, FREITAS, RAFAEL..."


In [11]:
df = df_origin.copy()

# Carregamento e prediçao do modelo 1

In [12]:
m1 = load('../../rf_exp2.joblib')

In [13]:
def preprocess(relato):
    def remove_stop_words(relato):
        # Remove stop words em português
        sw = stopwords.words('portuguese')
        sw = [unidecode(word).upper() for word in sw]
        return ' '.join([token for token in re.split("[, ]", relato) if len(token) > 2 and token not in sw])
    
    def clean_relato(relato):
        # Remoção de números e pontuação
        relato = re.sub(r'(<[^<>]*>)|(&NBSP;)|(&nbsp;)', " ", relato)
        relato = re.sub(r"[^\w\s]", " ", relato)
        relato = re.sub(r"[\d]", " ", relato)
        relato = remove_stop_words(relato)
        return relato
    
    relato = clean_relato(relato)
    return relato

def normalize_text(text):
    if pd.isna(text):
        return text
    text = unicodedata.normalize('NFKD', text)
    text = ''.join(c for c in text if not unicodedata.combining(c))
    return text.upper()

print("Iniciando pré-processamento...")
df['relato'] = df['relato'].apply(normalize_text)
df['relato_tratado'] = df['relato'].apply(preprocess)
print("Pré-processamento finalizado!")

def loadOutputList(df_bop : pd.DataFrame):
    rf_exp_2 = load('../../rf_exp2.joblib')

    output_list = []

    for text in df_bop['relato_tratado']:
        text = text.split()
        df = pd.DataFrame(text, columns=['palavra'])

        df['y_palavra'] = rf_exp_2.predict(df['palavra'].to_list())

        for _, row in df.iterrows():
            output_list.append({
                'palavra': row['palavra'],
                'y_palavra': int(row['y_palavra']),
            })
        output_list.append({
                'palavra': '#',
                'y_palavra': 2,
            })
    
    output_list.pop()

    return pd.DataFrame(output_list)
print("Carregando predição do modelo...")
output_list = loadOutputList(df)
print("Base de dados de predição criada!")

Iniciando pré-processamento...
Pré-processamento finalizado!
Carregando predição do modelo...
Base de dados de predição criada!


# Carregamento e prediçao do modelo 2

In [14]:
m2 = load('../../rf_corretor.joblib')

In [15]:
def vector_input_corretor(output_list: pd.DataFrame):
    nlp = scy.load('pt_core_news_lg')
    def LoadPedSucWord(output_list: pd.DataFrame):
        list_aux_psw = []

        df_aux = output_list.copy()
        df_aux['predecessor'] = df_aux['palavra'].shift(1).fillna('#')

        palavra_to_y = df_aux.set_index('palavra')['y_palavra'].to_dict()
        df_aux['y_predecessor'] = df_aux['predecessor'].map(lambda x: palavra_to_y.get(x, 2))

        df_aux['sucessor'] = df_aux['palavra'].shift(-1).fillna('#')
        df_aux['y_sucessor'] = df_aux['sucessor'].map(lambda x: palavra_to_y.get(x, 2))

        for _, row in df_aux.iterrows():
            list_aux_psw.append({
                'predecessor': row['predecessor'],
                'y_predecessor': int(row['y_predecessor']),
                'palavra': row['palavra'],
                'y_palavra': int(row['y_palavra']),
                'sucessor': row['sucessor'],
                'y_sucessor': int(row['y_sucessor']),
            })
        return pd.DataFrame(df_aux)

    def bigrams_vector(lista_tokens):
        vectorizer = load('../../vectorizer.joblib')
        alfabeto = list(string.ascii_uppercase)
        alfabeto_bigrams = [''.join(bigram) for bigram in list(product(alfabeto, repeat=2))]
        vector = vectorizer.transform(lista_tokens)
        return pd.DataFrame(vector.todense(), columns=alfabeto_bigrams)

    def create_base_cg(lista_tokens):
        mapeamento_pos = {
            'NOUN': '<SUBSTANTIVO>',
            'PROPN': '<SUBSTANTIVO>',
            'VERB': '<VERBO>',
            'AUX': '<VERBO>',
            'ADJ': '<ADJETIVO>',
            'ADV': '<ADVERBIO>',
            'PUNCT': '<PONTUACAO>',
            'CCONJ': '<CONJUNCAO>',
            'SCONJ': '<CONJUNCAO>',
            'PRON': '<PRONOME>',
            'DET': '<ARTIGO>',
            'ADP': '<PREPOSIÇÃO>',
            'NUM': '<NUMERAL>',
            'SYM': '<SIMBOLO>',
            'X': '<PALAVRA ESTRANGEIRA>',
            'SPACE': '<ESPACO>',
        }

        word_class = []
        tokens_to_process = []
        index_map = []

        # Coleta apenas os tokens que precisam ser processados
        for i, token in enumerate(lista_tokens):
            if token == '#':
                word_class.append('<NULL>')
            else:
                tokens_to_process.append(token.lower())
                index_map.append(i)
                word_class.append(None)  # placeholder para preencher depois

        # Processamento em lote com spacy.pipe
        docs = list(nlp.pipe(tokens_to_process, disable=["ner", "parser"]))  # desativa o que não é necessário

        for i, doc in enumerate(docs):
            classes = [mapeamento_pos.get(token.pos_, token.pos_) for token in doc]
            index = index_map[i]
            num_palavras = len(lista_tokens[index].split())

            # Evita erro se token dividido tiver menos classes do que palavras (ex. stopwords, erros etc)
            for j in range(num_palavras):
                word_class[index + j] = classes[j] if j < len(classes) else '<DESCONHECIDO>'

        df_resultado = pd.DataFrame({'palavra': lista_tokens, 'classe': word_class})

        return df_resultado

    def transformLabelsCG(tokens_vector_bigrams: pd.DataFrame):
        lb = LabelEncoder()
        labels = ['<SUBSTANTIVO>', '<VERBO>', '<ADJETIVO>', '<ADVERBIO>', '<PONTUACAO>',
                  '<CONJUNCAO>', '<PRONOME>', '<ARTIGO>', '<PREPOSIÇÃO>', '<NUMERAL>',
                  '<SIMBOLO>', '<PALAVRA ESTRANGEIRA>', '<ESPACO>', '<NULL>']
        lb.fit(labels)

        tokens_vector_bigrams['cg_p'] = lb.transform(tokens_vector_bigrams['cg_p'])
        tokens_vector_bigrams['cg_w'] = lb.transform(tokens_vector_bigrams['cg_w'])
        tokens_vector_bigrams['cg_s'] = lb.transform(tokens_vector_bigrams['cg_s'])

        return tokens_vector_bigrams

    # Etapa 1: Predecessores e Sucessores
    print("Realizando coleta de predecessores e sucessores...")
    temp_list = LoadPedSucWord(output_list)
    temp_list = temp_list[temp_list['y_palavra'] == 0].reset_index()
    indices_originais = temp_list['index']
    print(f"Predecessores e Sucessores coletados!")

    # Etapa 2: Vetor de Bigramas
    print("Criando vetor de bigramas para os tokens...")
    token = temp_list['palavra']
    tokens_vector_bigrams = bigrams_vector(token.to_list())
    print(f"Vetores de bigramas criados!")

    # Etapa 3: Concatenação
    print("Concatenando vetor de bigramas com dados de predecessores e sucessores...")
    tokens_vector_bigrams = pd.concat([
        tokens_vector_bigrams,
        temp_list[['predecessor','y_predecessor', 'palavra', 'y_palavra','sucessor', 'y_sucessor']]
    ], axis=1)
    print(f"Concatenação concluída!")

    # Etapa 4: Classificação gramatical
    print("Realizando classificação gramatical dos tokens...")
    tokens_vector_bigrams['cg_p'] = create_base_cg(tokens_vector_bigrams['predecessor'])['classe']
    tokens_vector_bigrams['cg_w'] = create_base_cg(tokens_vector_bigrams['palavra'])['classe']
    tokens_vector_bigrams['cg_s'] = create_base_cg(tokens_vector_bigrams['sucessor'])['classe']
    print(f"Classificação gramatical concluída!")

    # Etapa 5: Transformação dos labels
    print("Transformando labels da classificação gramatical...")
    tokens_vector_bigrams = transformLabelsCG(tokens_vector_bigrams)
    print(f"Transformação concluída!")

    # Etapa 6: Remoção de colunas desnecessárias
    print("Removendo colunas desnecessárias...")
    final_tokens_vector_bigrams = tokens_vector_bigrams.drop(['sucessor', 'predecessor','palavra','y_palavra'], axis=1)
    print(f"Remoção concluída!")

    print("Vetor de entrada para o modelo gerado com sucesso!")

    return final_tokens_vector_bigrams, indices_originais


In [16]:
vector_input_temp_list, indices_originais = vector_input_corretor(output_list)

Realizando coleta de predecessores e sucessores...
Predecessores e Sucessores coletados!
Criando vetor de bigramas para os tokens...
Vetores de bigramas criados!
Concatenando vetor de bigramas com dados de predecessores e sucessores...
Concatenação concluída!
Realizando classificação gramatical dos tokens...
Classificação gramatical concluída!
Transformando labels da classificação gramatical...
Transformação concluída!
Removendo colunas desnecessárias...
Remoção concluída!
Vetor de entrada para o modelo gerado com sucesso!


# substituindo os dados do modelo 1

In [17]:
def corrector_pred_m1(vector_input_temp_list, indices_originais):
    result = m2.predict(vector_input_temp_list)
    temp_list = pd.DataFrame({'y_pred':result})
    temp_list = pd.concat([temp_list, indices_originais], axis=1)
    # select_index = output_list['y_palavra'][temp_list['index'].to_list()]
    
    for idx, pred_Corretor in zip(temp_list['index'].to_list(), temp_list['y_pred'].to_list()):
        if int(pred_Corretor) == 1:
            output_list['y_palavra'][idx] = pred_Corretor

In [18]:
new_pred = corrector_pred_m1(vector_input_temp_list, indices_originais)

C:\Users\joaol\AppData\Local\Temp\ipykernel_43752\3522035133.py:9: FutureWarning: ChainedAssignmentError: behaviour will change in pandas 3.0!
You are setting values through chained assignment. Currently this works in certain cases, but when using Copy-on-Write (which will become the default behaviour in pandas 3.0) this will never work to update the original DataFrame or Series, because the intermediate object on which we are setting values will behave as a copy.
A typical example is when you are setting values in a column of a DataFrame, like:

df["col"][row_indexer] = value

Use `df.loc[row_indexer, "col"] = values` instead, to perform the assignment in a single step and ensure this keeps updating the original `df`.

See the caveats in the documentation: https://pandas.pydata.org/pandas-docs/stable/user_guide/indexing.html#returning-a-view-versus-a-copy

  output_list['y_palavra'][idx] = pred_Corretor
C:\Users\joaol\AppData\Local\Temp\ipykernel_43752\3522035133.py:9: SettingWithCopy

# Função que atualiza os dados, anonimizando os nomes preditos.

In [19]:
def anon_text():
    df['relato_anon'] = df['relato'].apply(lambda words_text: ' '.join(
        ['***' if token in output_list[output_list['y_palavra'] == 1]['palavra'].values else token 
         for token in words_text.split(' ')]
    ))
    return df

In [20]:
df_anon = anon_text()
df_anon

,n_bop,relato,nomes,relato_tratado,relato_anon
0,1,"SUBJETIVO NEFROLOGIA 220 A - ALICE MORAES , 37...","ALICE, MORAES, PAULO, SOUSA, MATOS",SUBJETIVO NEFROLOGIA ALICE MORAES ANOS PROFESS...,"SUBJETIVO *** 220 A - *** *** , 37 ANOS, PROFE..."
1,2,SUBJETIVO FISIOTERAPIA 402 A - RAFAELA MARTINS...,"RAFAELA, MARTINS, MARIA, SILVA, FERNANDO, CRUZ...",SUBJETIVO FISIOTERAPIA RAFAELA MARTINS ANOS DE...,"SUBJETIVO FISIOTERAPIA 402 A - *** *** , 28 AN..."
2,3,SUBJETIVO CARDIOLOGIA 205 A - RICARDO GONCALVE...,"RICARDO, GONÇALVES, ANDRÉ, FERNANDA, LIMA, OLI...",SUBJETIVO CARDIOLOGIA RICARDO GONCALVES ANOS A...,"SUBJETIVO *** 205 A - *** *** , 58 ANOS, ADVOG..."
3,4,SUBJETIVO GASTROENTEROLOGIA PACIENTE : PEDRO S...,"PEDRO, SANTOS, LUISA, FERNANDES",SUBJETIVO GASTROENTEROLOGIA PACIENTE PEDRO SAN...,"SUBJETIVO GASTROENTEROLOGIA *** : *** *** , 54..."
4,5,"SUBJETIVO ORTOPEDIA 78 A - JOANA MARTINS , 52 ...","JOANA, MARTINS, RENATA, COSTA",SUBJETIVO ORTOPEDIA JOANA MARTINS ANOS PROFESS...,"SUBJETIVO *** 78 A - *** *** , 52 ANOS, PROFES..."
...,...,...,...,...,...
1881,1882,SUBJETIVO UER - SALA LARANJA ID : CLAUDIA SOAR...,"CLÁUDIA, SOARES, ALMEIDA, PEDRO, LARISSA, GOME...",SUBJETIVO UER SALA LARANJA CLAUDIA SOARES ALME...,SUBJETIVO *** - *** *** ID : *** *** *** DT NA...
1882,1883,SUBJETIVO UER - SALA AMARELA ID : RENATO AUGUS...,"RENATO, AUGUSTO, MOREIRA, FERNANDA, LOPES, SAM...",SUBJETIVO UER SALA AMARELA RENATO AUGUSTO MORE...,"SUBJETIVO *** - *** *** ID : *** *** *** , 21 ..."
1883,1884,SUBJETIVO UER - SALA AMARELA ID : GERTRUDES SI...,"GERTRUDES, SILVA, CARNEIRO, CLARISSA, DIEGO, H...",SUBJETIVO UER SALA AMARELA GERTRUDES SILVA CAR...,SUBJETIVO *** - *** *** ID : *** *** *** DT NA...
1884,1885,SUBJETIVO CENTRO DE SAUDE - CONSULTORIO ID : E...,"ELIANA, COSTA, SILVA, MARIANA, FREITAS, RAFAEL...",SUBJETIVO CENTRO SAUDE CONSULTORIO ELIANA COST...,SUBJETIVO *** DE *** - *** ID : *** *** *** DT...


In [21]:
df_anon['relato_anon'].drop_duplicates()

0       SUBJETIVO *** 220 A - *** *** , 37 ANOS, PROFE...
1       SUBJETIVO FISIOTERAPIA 402 A - *** *** , 28 AN...
2       SUBJETIVO *** 205 A - *** *** , 58 ANOS, ADVOG...
3       SUBJETIVO GASTROENTEROLOGIA *** : *** *** , 54...
4       SUBJETIVO *** 78 A - *** *** , 52 ANOS, PROFES...
                              ...                        
1881    SUBJETIVO *** - *** *** ID : *** *** *** DT NA...
1882    SUBJETIVO *** - *** *** ID : *** *** *** , 21 ...
1883    SUBJETIVO *** - *** *** ID : *** *** *** DT NA...
1884    SUBJETIVO *** DE *** - *** ID : *** *** *** DT...
1885    SUBJETIVO *** - *** *** ID : *** *** DA *** DT...
Name: relato_anon, Length: 1886, dtype: object

In [22]:
df_anon['relato_anon'].values

array(['SUBJETIVO *** 220 A - *** *** , 37 ANOS, PROFESSORA *** : 08:10 *** : *** EM *** PERITONEAL, SEM *** DE PERITONITE. PERMEABILIDADE DE *** PRESERVADA. *** *** 5,2 MG DL . HEMODINAMICO : NORMOTENSO, SEM VARIACOES SIGNIFICATIVAS DE *** *** PA 128 75 *** . FC EM *** *** DE 82 BPM. *** : SEM *** OU OUTROS *** DE *** HIDRICA. AP : *** VESICULARES *** E NORMAIS. *** : *** 4 EM *** INFERIORES, *** INTEGRA E HIDRATADA, *** *** CUTANEA. CONDUTAS : *** *** *** CONFORME PRESCRICAO. *** DE *** HIPO-SODICA. *** *** DE *** LABORATORIAIS E *** SECO. ELABORADO E ASSINADO POR DR. *** *** *** , *** 122345 EM 20 07 2022 16:18. CONTACTAR *** *** DO *** 11 98765-4321 OU E-MAIL ALICE.MORAES@ESCOLA.EDU . RESIDENTA EM *** PAULISTA , SAO *** . IDENTIFICADOR DO ATENDIMENTO 582734 .',
       'SUBJETIVO FISIOTERAPIA 402 A - *** *** , 28 ANOS, *** GRAFICA *** : 08:15 NEUROLOGICO : *** DESPERTA, SEM SEDACAO, INTERAGINDO COM A EQUIPE, SEM *** NEUROLOGICAS. HEMODINAMICO : *** ESTAVEL, NAO NECESSITA DE *** VASO

In [23]:
df_anon.to_csv(PATH_BASE_ANONIMIZADA_CORRETOR, index=False)